# Logistics and Product Development in the Automobile Industry — Component K7

This notebook is self-contained and follows the repository structure from the assignment. It:

1. loads `Komponente_K7.csv` and `Logistikverzug_K7.csv` from `data/raw/`,
2. creates the derived **Logistics delay** dataset in `data/processed/general_tasks/`,
3. investigates the distribution statistically,
4. computes the mean delay in **working days** (weekends excluded),
5. visualizes the distribution with Plotly, and
6. demonstrates a decision-tree workflow for classifying `Fehlerhaft`.

> **Important convention:** goods are assumed to be issued exactly one calendar day after `Produktionsdatum`. A transit from an issue date to the same receiving date therefore has a working-day delay of 0. `numpy.busday_count` excludes Saturdays and Sundays.

In [17]:
# Imports
from pathlib import Path
import re
import warnings

import numpy as np
import pandas as pd
import plotly.express as px
import plotly.graph_objects as go
from plotly.subplots import make_subplots

from scipy import stats

from sklearn.compose import ColumnTransformer
from sklearn.impute import SimpleImputer
from sklearn.model_selection import train_test_split, GridSearchCV, StratifiedKFold, cross_val_score
from sklearn.pipeline import Pipeline
from sklearn.preprocessing import OneHotEncoder
from sklearn.tree import DecisionTreeClassifier, plot_tree
from sklearn.metrics import (
    classification_report,
    confusion_matrix,
    ConfusionMatrixDisplay,
    roc_auc_score,
)

import matplotlib.pyplot as plt

warnings.filterwarnings('ignore')
pd.set_option('display.max_columns', 100)
pd.set_option('display.width', 140)


## 0. Paths and robust CSV loading

The helper below makes the notebook work whether it is launched from the repository root or from `notebooks/general_tasks/`. CSV separators and encodings are detected flexibly because database exports often use semicolons and German encodings.

In [18]:
def find_repo_root(start: Path | None = None) -> Path:
    """Find the repository root by looking for data/raw and notebooks folders."""
    start = (start or Path.cwd()).resolve()
    candidates = [start, *start.parents]
    for p in candidates:
        if (p / 'data' / 'raw').exists() and (p / 'notebooks').exists():
            return p
    # Fallback: assumes notebook is in <root>/notebooks/general_tasks
    if start.name == 'general_tasks' and start.parent.name == 'notebooks':
        return start.parent.parent
    raise FileNotFoundError(
        'Repository root not found. Run this notebook inside the project structure '
        'that contains data/raw and notebooks/.'
    )


def read_csv_robust(path: Path) -> pd.DataFrame:
    """Read a CSV with automatic separator detection and common encodings."""
    last_error = None
    for encoding in ('utf-8-sig', 'utf-8', 'cp1252', 'latin1'):
        try:
            return pd.read_csv(path, sep=None, engine='python', encoding=encoding)
        except Exception as exc:
            last_error = exc
    raise RuntimeError(f'Could not read {path}: {last_error}')


ROOT = find_repo_root()
RAW = ROOT / 'data' / 'raw' / 'Logistikverzug'
PROCESSED = ROOT / 'data' / 'processed' / 'general_tasks'
PROCESSED.mkdir(parents=True, exist_ok=True)

COMPONENT_FILE = RAW / 'Komponente_K7.csv'
LOGISTICS_FILE = RAW / 'Logistikverzug_K7.csv'

for f in (COMPONENT_FILE, LOGISTICS_FILE):
    if not f.exists():
        raise FileNotFoundError(f'Missing required file: {f}')

component = read_csv_robust(COMPONENT_FILE)
logistics = read_csv_robust(LOGISTICS_FILE)

print('Repository root:', ROOT)
print('Komponente_K7 shape:', component.shape)
print('Logistikverzug_K7 shape:', logistics.shape)
print('\nComponent columns:')
print(component.columns.tolist())
print('\nLogistics columns:')
print(logistics.columns.tolist())


Repository root: /Users/alexanderfridrich/Studium programmieren/QWIDA/Data-Analysis-Case-Study
Komponente_K7 shape: (306490, 6)
Logistikverzug_K7 shape: (306490, 6)

Component columns:
['Unnamed: 0', 'IDNummer', 'Produktionsdatum', 'Herstellernummer', 'Werksnummer', 'Fehlerhaft']

Logistics columns:
['Unnamed: 0', 'IDNummer', 'Wareneingang', 'Herstellernummer', 'Werksnummer', 'Fehlerhaft']


## 1. Create the “Logistics delay” dataset

The merge should be performed with a genuine record identifier (for example an order, serial, component, or production ID), **not by row position**. The code first looks for exact common columns and prioritizes ID-like names. If your export uses a different identifier, set `JOIN_KEY` manually in the cell below.

The derived fields are:

- `Produktionsdatum`
- `Ausgabedatum = Produktionsdatum + 1 day`
- `Wareneingang`
- `Logistikverzug_Kalendertage`
- `Logistikverzug_Arbeitstage` (Saturday/Sunday excluded)

In [19]:
# ---------- Column identification ----------
def normalize_name(s: str) -> str:
    return re.sub(r'[^a-z0-9]+', '', str(s).lower())


def find_column(df: pd.DataFrame, candidates: list[str], required=True):
    normalized = {normalize_name(c): c for c in df.columns}
    for cand in candidates:
        key = normalize_name(cand)
        if key in normalized:
            return normalized[key]
    if required:
        raise KeyError(
            f'None of the expected columns {candidates} were found. Available columns: {df.columns.tolist()}'
        )
    return None


PRODUCTION_COL = find_column(
    component,
    ['Produktionsdatum', 'Produktion Datum', 'ProductionDate', 'Production Date']
)
RECEIPT_COL = find_column(
    logistics,
    ['Wareneingang', 'Wareneingangsdatum', 'ReceivingDate', 'GoodsReceipt', 'Goods Receipt']
)

# Set this manually if the automatic selection is not the correct business key.
JOIN_KEY = None

if JOIN_KEY is None:
    common = [c for c in component.columns if c in logistics.columns]
    excluded = {PRODUCTION_COL, RECEIPT_COL}
    common = [c for c in common if c not in excluded]

    # Prefer columns that look like stable identifiers.
    id_tokens = ('id', 'nr', 'nummer', 'auftrag', 'order', 'serial', 'serie', 'los', 'charge', 'komponente')
    ranked = sorted(
        common,
        key=lambda c: (
            0 if any(tok in normalize_name(c) for tok in id_tokens) else 1,
            -component[c].nunique(dropna=True),
        )
    )
    if not ranked:
        raise KeyError(
            'No common merge key was found. Set JOIN_KEY manually to the record identifier '
            'present in both CSV files.'
        )
    JOIN_KEY = ranked[0]

print('Production date column:', PRODUCTION_COL)
print('Receiving date column:', RECEIPT_COL)
print('Selected merge key:', JOIN_KEY)

# Validate key quality before merging.
print('\nKey diagnostics:')
print('Component duplicate keys:', component[JOIN_KEY].duplicated().sum())
print('Logistics duplicate keys:', logistics[JOIN_KEY].duplicated().sum())
print('Component missing keys:', component[JOIN_KEY].isna().sum())
print('Logistics missing keys:', logistics[JOIN_KEY].isna().sum())


Production date column: Produktionsdatum
Receiving date column: Wareneingang
Selected merge key: IDNummer

Key diagnostics:
Component duplicate keys: 0
Logistics duplicate keys: 0
Component missing keys: 0
Logistics missing keys: 0


In [20]:
# ---------- Parse dates and merge ----------
component_work = component.copy()
logistics_work = logistics.copy()

component_work[PRODUCTION_COL] = pd.to_datetime(
    component_work[PRODUCTION_COL], errors='coerce', dayfirst=True
)
logistics_work[RECEIPT_COL] = pd.to_datetime(
    logistics_work[RECEIPT_COL], errors='coerce', dayfirst=True
)

# Only bring the fields required for the logistics-delay dataset from the two sources.
left = component_work[[JOIN_KEY, PRODUCTION_COL]].copy()
right = logistics_work[[JOIN_KEY, RECEIPT_COL]].copy()

# m:1 / 1:1 can be tightened after inspecting duplicate-key diagnostics.
logistics_delay = left.merge(right, on=JOIN_KEY, how='inner', validate='many_to_many')

logistics_delay = logistics_delay.rename(columns={
    PRODUCTION_COL: 'Produktionsdatum',
    RECEIPT_COL: 'Wareneingang'
})

logistics_delay['Ausgabedatum'] = logistics_delay['Produktionsdatum'] + pd.Timedelta(days=1)
logistics_delay['Logistikverzug_Kalendertage'] = (
    logistics_delay['Wareneingang'] - logistics_delay['Ausgabedatum']
).dt.days

# Working-day delay: counts Mon-Fri in [Ausgabedatum, Wareneingang).
def working_days_between(start, end):
    if pd.isna(start) or pd.isna(end):
        return np.nan
    start_d = np.datetime64(pd.Timestamp(start).date(), 'D')
    end_d = np.datetime64(pd.Timestamp(end).date(), 'D')
    if end_d < start_d:
        return -np.busday_count(end_d, start_d)
    return np.busday_count(start_d, end_d)

logistics_delay['Logistikverzug_Arbeitstage'] = [
    working_days_between(s, e)
    for s, e in zip(logistics_delay['Ausgabedatum'], logistics_delay['Wareneingang'])
]

# Keep missing rows visible for diagnostics, but exclude impossible negative transit times from modelling.
print('Merged rows:', len(logistics_delay))
print('Missing production dates:', logistics_delay['Produktionsdatum'].isna().sum())
print('Missing receipt dates:', logistics_delay['Wareneingang'].isna().sum())
print('Negative calendar delays:', (logistics_delay['Logistikverzug_Kalendertage'] < 0).sum())

logistics_delay_clean = logistics_delay.dropna(
    subset=['Produktionsdatum', 'Wareneingang', 'Logistikverzug_Arbeitstage']
).copy()
logistics_delay_clean = logistics_delay_clean[
    logistics_delay_clean['Logistikverzug_Arbeitstage'] >= 0
].reset_index(drop=True)

OUTPUT_FILE = PROCESSED / 'Logistics delay.csv'
logistics_delay_clean.to_csv(OUTPUT_FILE, index=False, encoding='utf-8-sig')

print('\nSaved:', OUTPUT_FILE)
display(logistics_delay_clean.head())


Merged rows: 306490
Missing production dates: 185848
Missing receipt dates: 0
Negative calendar delays: 55265

Saved: /Users/alexanderfridrich/Studium programmieren/QWIDA/Data-Analysis-Case-Study/data/processed/general_tasks/Logistics delay.csv


,IDNummer,Produktionsdatum,Wareneingang,Ausgabedatum,Logistikverzug_Kalendertage,Logistikverzug_Arbeitstage
0,K7-114-1142-1770,2008-01-12,2008-12-07,2008-01-13,329.0,235.0
1,K7-114-1142-1771,2008-01-12,2008-12-10,2008-01-13,332.0,237.0
2,K7-114-1142-1772,2008-01-12,2008-12-08,2008-01-13,330.0,235.0
3,K7-114-1142-1773,2008-01-12,2008-12-09,2008-01-13,331.0,236.0
4,K7-114-1142-1774,2008-01-12,2008-12-08,2008-01-13,330.0,235.0


## a. How is the logistics delay distributed?

### Approach

Because the observed delay is non-negative and can be right-skewed, I do **not** assume normality in advance. The workflow is:

1. inspect summary statistics and skewness;
2. test normality with **Shapiro–Wilk** (for up to 5,000 observations) and **D’Agostino’s K²** (when sample size permits);
3. compare several plausible continuous approximations — Normal, Exponential, Gamma, Lognormal and Weibull — using maximum-likelihood fitting;
4. rank them mainly by **AIC** and report an approximate one-sample **Kolmogorov–Smirnov** statistic.

The working-day variable is integer-valued, so continuous distributions are approximations. A discrete count model (e.g. Poisson or negative binomial) is a reasonable alternative if the discrete nature of the delay is central to the analysis. The KS p-values below should be treated as descriptive because parameters are estimated from the same sample.

In [21]:
delay = logistics_delay_clean['Logistikverzug_Arbeitstage'].astype(float)

print(delay.describe())
print(f'\nSkewness: {stats.skew(delay, bias=False):.3f}')
print(f'Excess kurtosis: {stats.kurtosis(delay, fisher=True, bias=False):.3f}')

# Normality tests
normality_results = []

if len(delay) >= 3:
    sample_for_shapiro = delay.sample(min(len(delay), 5000), random_state=42)
    sh_stat, sh_p = stats.shapiro(sample_for_shapiro)
    normality_results.append(('Shapiro-Wilk', sh_stat, sh_p))

if len(delay) >= 8:
    k2_stat, k2_p = stats.normaltest(delay)
    normality_results.append(("D'Agostino K^2", k2_stat, k2_p))

normality_df = pd.DataFrame(normality_results, columns=['Test', 'Statistic', 'p_value'])
display(normality_df)

alpha = 0.05
if not normality_df.empty:
    if (normality_df['p_value'] < alpha).all():
        print('Conclusion at alpha=0.05: normality is rejected by all reported normality tests.')
    else:
        print('Conclusion at alpha=0.05: the normality evidence is mixed / insufficient to reject in every test.')


count    65377.000000
mean        81.377824
std         61.395274
min          1.000000
25%         26.000000
50%         68.000000
75%        130.000000
max        238.000000
Name: Logistikverzug_Arbeitstage, dtype: float64

Skewness: 0.566
Excess kurtosis: -0.624


,Test,Statistic,p_value
0,Shapiro-Wilk,0.931266,4.133830e-43
1,D'Agostino K^2,5438.167762,0.000000e+00


Conclusion at alpha=0.05: normality is rejected by all reported normality tests.


In [22]:
# ---------- Candidate distribution comparison ----------
# A small shift by +1 allows strictly-positive families (lognormal/gamma/weibull)
# to represent observations that can legitimately be zero working days.
x = delay.to_numpy()
x_pos = x + 1.0

candidate_specs = {
    'Normal':       (stats.norm, x, {}),
    'Exponential':  (stats.expon, x, {'floc': 0}),
    'Gamma (+1)':   (stats.gamma, x_pos, {'floc': 0}),
    'Lognormal (+1)': (stats.lognorm, x_pos, {'floc': 0}),
    'Weibull (+1)': (stats.weibull_min, x_pos, {'floc': 0}),
}

rows = []
fitted_models = {}

for name, (dist, data_used, fit_kwargs) in candidate_specs.items():
    try:
        params = dist.fit(data_used, **fit_kwargs)
        loglik = np.sum(dist.logpdf(data_used, *params))
        k = len(params) - len(fit_kwargs)  # approximate number of estimated parameters
        aic = 2 * k - 2 * loglik
        ks_stat, ks_p = stats.kstest(data_used, dist.cdf, args=params)
        rows.append({
            'Distribution': name,
            'AIC': aic,
            'KS_statistic': ks_stat,
            'KS_p_value_approx': ks_p,
            'Parameters': params,
        })
        fitted_models[name] = (dist, params)
    except Exception as exc:
        rows.append({
            'Distribution': name,
            'AIC': np.nan,
            'KS_statistic': np.nan,
            'KS_p_value_approx': np.nan,
            'Parameters': f'Fit failed: {exc}',
        })

fit_results = pd.DataFrame(rows).sort_values('AIC', na_position='last').reset_index(drop=True)
display(fit_results)

best_distribution = fit_results.loc[0, 'Distribution']
print(f'Best candidate by AIC: {best_distribution}')
print(
    'Interpretation: the preferred family is the one with the smallest AIC among the tested candidates. '
    'Use the histogram/KDE below to confirm that the fitted shape is also visually plausible.'
)


,Distribution,AIC,KS_statistic,KS_p_value_approx,Parameters
0,Weibull (+1),704395.896671,0.105979,0.0,"(1.2090198205957141, 0, 87.30014594333446)"
1,Gamma (+1),705849.186753,0.105002,0.0,"(1.234582020288926, 0, 66.72527434516299)"
2,Exponential,705956.287972,0.126945,0.0,"(0.0, 81.37782400538416)"
3,Lognormal (+1),721263.274942,0.157612,0.0,"(1.1533903007052002, 0, 52.17014238102186)"
4,Normal,723892.630227,0.125509,0.0,"(81.37782400538416, 61.39480458648857)"


Best candidate by AIC: Weibull (+1)
Interpretation: the preferred family is the one with the smallest AIC among the tested candidates. Use the histogram/KDE below to confirm that the fitted shape is also visually plausible.


## b. Mean logistics delay in working days

The primary measure is the arithmetic mean of `Logistikverzug_Arbeitstage`. Weekends are excluded. This gives the expected weekday transit duration for a randomly selected K7 shipment in the observed sample.

Useful alternatives are the **median** (robust against unusually long delays), a **trimmed mean**, percentiles such as P90/P95 for service-level planning, or a calendar-day measure when customers care about elapsed time rather than operational workdays.

In [23]:
mean_workdays = delay.mean()
median_workdays = delay.median()
trimmed_mean_10 = stats.trim_mean(delay, proportiontocut=0.10)
p90 = delay.quantile(0.90)
p95 = delay.quantile(0.95)

summary_b = pd.DataFrame({
    'Metric': ['Mean', 'Median', '10% trimmed mean', '90th percentile', '95th percentile'],
    'Working days': [mean_workdays, median_workdays, trimmed_mean_10, p90, p95]
})
display(summary_b)

print(
    f'Interpretation: on average, a K7 component spends about {mean_workdays:.2f} working days '
    'between the assumed issue date and goods receipt. '
    f'The median is {median_workdays:.2f} working days, which is useful when the distribution is skewed.'
)


,Metric,Working days
0,Mean,81.377824
1,Median,68.000000
2,10% trimmed mean,76.306005
3,90th percentile,173.000000
4,95th percentile,194.000000


Interpretation: on average, a K7 component spends about 81.38 working days between the assumed issue date and goods receipt. The median is 68.00 working days, which is useful when the distribution is skewed.


## c. Plotly histogram and density function

For the histogram bin size I use the **Freedman–Diaconis rule**:

\[
\text{bin width} = 2\cdot IQR(x)\cdot n^{-1/3}
\]

It is robust to skewness and outliers because it uses the interquartile range. Since logistics delay is measured in whole working days, the computed width is rounded to at least 1 day. If the IQR is zero, the code falls back to Sturges’ rule.

The density curve is a Gaussian kernel density estimate (KDE). It is shown as a smooth descriptive representation of the empirical distribution.

In [24]:
# ---------- Bin width: Freedman-Diaconis with robust fallback ----------
def fd_bin_width(values):
    values = np.asarray(values, dtype=float)
    values = values[np.isfinite(values)]
    n = len(values)
    if n < 2:
        return 1.0
    q25, q75 = np.percentile(values, [25, 75])
    iqr = q75 - q25
    width = 2 * iqr * n ** (-1/3)
    if not np.isfinite(width) or width <= 0:
        # Sturges fallback converted to a width.
        bins = max(1, int(np.ceil(np.log2(n) + 1)))
        data_range = values.max() - values.min()
        width = data_range / bins if data_range > 0 else 1.0
    return max(1.0, float(np.ceil(width)))

bin_width = fd_bin_width(delay)
print(f'Freedman-Diaconis bin width used: {bin_width:.0f} working day(s)')

# KDE grid
x_grid = np.linspace(max(0, delay.min() - 0.5), delay.max() + 1.0, 500)
if delay.nunique() > 1:
    kde = stats.gaussian_kde(delay)
    kde_y = kde(x_grid)
else:
    kde_y = np.zeros_like(x_grid)

fig = go.Figure()
fig.add_trace(go.Histogram(
    x=delay,
    histnorm='probability density',
    xbins=dict(
        start=float(np.floor(delay.min())),
        end=float(np.ceil(delay.max()) + bin_width),
        size=float(bin_width),
    ),
    name='Histogram',
    opacity=0.65,
))
fig.add_trace(go.Scatter(
    x=x_grid,
    y=kde_y,
    mode='lines',
    name='KDE density',
))

fig.update_layout(
    title='Distribution of logistics delay — Component K7',
    xaxis_title='Logistics delay (working days)',
    yaxis_title='Density',
    bargap=0.05,
    template='plotly_white',
)
fig.show()


Freedman-Diaconis bin width used: 6 working day(s)


In [25]:
# Optional: overlay the AIC-best fitted continuous candidate for comparison.
name = best_distribution
dist, params = fitted_models[name]

if '(+1)' in name:
    fitted_y = dist.pdf(x_grid + 1.0, *params)
else:
    fitted_y = dist.pdf(x_grid, *params)

fig2 = go.Figure()
fig2.add_trace(go.Histogram(
    x=delay,
    histnorm='probability density',
    xbins=dict(size=float(bin_width)),
    name='Histogram',
    opacity=0.60,
))
fig2.add_trace(go.Scatter(x=x_grid, y=kde_y, mode='lines', name='KDE'))
fig2.add_trace(go.Scatter(x=x_grid, y=fitted_y, mode='lines', name=f'Fitted {name}'))
fig2.update_layout(
    title=f'K7 logistics delay with fitted {name} distribution',
    xaxis_title='Logistics delay (working days)',
    yaxis_title='Density',
    template='plotly_white',
)
fig2.show()


## d. Decision-tree process for classifying `Fehlerhaft`

A defensible decision-tree workflow is:

1. **Define the target:** convert `Fehlerhaft` to a binary label.
2. **Choose predictors available before the quality outcome is known.** Exclude IDs, free-text fields, direct defect descriptions, and other leakage variables.
3. **Visualize relationships:** inspect class balance and compare candidate predictors by defect status (box plots for numeric variables and rate plots for categorical variables). This helps identify informative variables and data-quality problems.
4. **Split the data stratified by the target** so the defect ratio is similar in train and test sets.
5. **Preprocess inside a pipeline:** median-impute numeric variables; most-frequent-impute and one-hot encode categorical variables.
6. **Tune tree complexity** (`max_depth`, `min_samples_leaf`, `criterion`) with stratified cross-validation. This limits overfitting and keeps the tree interpretable.
7. **Evaluate on untouched test data** with confusion matrix, precision/recall/F1, and ROC-AUC when both classes are present.
8. **Interpret the tree and feature importances.** A shallow tree can be translated into practical quality rules.

The code below automatically uses suitable columns from `Komponente_K7.csv`. Review `DROP_FROM_MODEL` carefully and add any columns that would leak information from after the defect decision.

In [26]:
# ---------- Prepare target ----------
TARGET_COL = find_column(
    component_work,
    ['Fehlerhaft', 'Defective', 'Fehler', 'IsDefective']
)

model_df = component_work.copy()

# Bring logistics delay into the component-level modelling table if the merge key is available.
# Only do this if logistics delay would genuinely be known at the time the classification is made.
model_df = model_df.merge(
    logistics_delay_clean[[JOIN_KEY, 'Logistikverzug_Arbeitstage']].drop_duplicates(subset=[JOIN_KEY]),
    on=JOIN_KEY,
    how='left'
)


def to_binary_target(series: pd.Series) -> pd.Series:
    if pd.api.types.is_bool_dtype(series):
        return series.astype(int)
    if pd.api.types.is_numeric_dtype(series):
        vals = sorted(pd.Series(series.dropna().unique()).tolist())
        if set(vals).issubset({0, 1}):
            return series.astype('Int64')
    mapping = {
        'ja': 1, 'yes': 1, 'y': 1, 'true': 1, '1': 1,
        'fehlerhaft': 1, 'defective': 1,
        'nein': 0, 'no': 0, 'n': 0, 'false': 0, '0': 0,
        'nicht fehlerhaft': 0, 'not defective': 0, 'i.o.': 0, 'io': 0,
    }
    converted = series.astype(str).str.strip().str.lower().map(mapping)
    if converted.notna().sum() == 0:
        raise ValueError(
            f'Could not map target column {series.name!r} to 0/1. '
            f'Observed values: {series.dropna().astype(str).unique()[:20]}'
        )
    return converted.astype('Int64')

model_df['_target'] = to_binary_target(model_df[TARGET_COL])
model_df = model_df.dropna(subset=['_target']).copy()
model_df['_target'] = model_df['_target'].astype(int)

print('Target column:', TARGET_COL)
print(model_df['_target'].value_counts(dropna=False))
print(model_df['_target'].value_counts(normalize=True).rename('share'))


Target column: Fehlerhaft
_target
0    306484
1         6
Name: count, dtype: int64
_target
0    0.99998
1    0.00002
Name: share, dtype: float64


In [27]:
# ---------- Visual diagnostics before modelling ----------
class_counts = model_df['_target'].map({0: 'Not defective', 1: 'Defective'}).value_counts().rename_axis('Class').reset_index(name='Count')
fig = px.bar(class_counts, x='Class', y='Count', title='Class balance: K7 defect status', text='Count')
fig.update_layout(template='plotly_white')
fig.show()

# Candidate numeric features, excluding obvious identifiers / target / raw dates.
exclude_names = {TARGET_COL, '_target', JOIN_KEY, PRODUCTION_COL}
num_candidates = [
    c for c in model_df.select_dtypes(include=np.number).columns
    if c not in exclude_names and model_df[c].nunique(dropna=True) > 1
]

# Show up to the six numeric variables with the strongest absolute point-biserial correlation.
ranked_numeric = []
for c in num_candidates:
    tmp = model_df[[c, '_target']].dropna()
    if tmp[c].nunique() > 1 and tmp['_target'].nunique() == 2:
        try:
            corr = stats.pointbiserialr(tmp['_target'], tmp[c]).statistic
            ranked_numeric.append((c, abs(corr)))
        except Exception:
            pass
ranked_numeric = [c for c, _ in sorted(ranked_numeric, key=lambda z: z[1], reverse=True)[:6]]

for c in ranked_numeric:
    tmp = model_df[[c, '_target']].copy()
    tmp['Status'] = tmp['_target'].map({0: 'Not defective', 1: 'Defective'})
    fig = px.box(
        tmp,
        x='Status',
        y=c,
        points='outliers',
        title=f'{c} by defect status'
    )
    fig.update_layout(template='plotly_white')
    fig.show()


In [28]:
# ---------- Feature selection and leakage protection ----------
# Add any post-outcome fields or direct defect indicators here after inspecting your dataset.
DROP_FROM_MODEL = [
    TARGET_COL,
    '_target',
    JOIN_KEY,
    PRODUCTION_COL,
]

# Automatically exclude raw datetime columns and columns that are effectively unique identifiers.
feature_candidates = [c for c in model_df.columns if c not in DROP_FROM_MODEL]
feature_candidates = [
    c for c in feature_candidates
    if not pd.api.types.is_datetime64_any_dtype(model_df[c])
]

id_like = []
for c in feature_candidates:
    nunique = model_df[c].nunique(dropna=True)
    ratio = nunique / max(1, len(model_df))
    name = normalize_name(c)
    if ratio > 0.95 and any(tok in name for tok in ('id', 'nr', 'nummer', 'serial', 'auftrag')):
        id_like.append(c)

feature_candidates = [c for c in feature_candidates if c not in id_like]

X = model_df[feature_candidates].copy()
y = model_df['_target'].copy()

numeric_features = X.select_dtypes(include=np.number).columns.tolist()
categorical_features = X.select_dtypes(exclude=np.number).columns.tolist()

print('Features used:', feature_candidates)
print('Automatically removed ID-like fields:', id_like)
print('Numeric:', numeric_features)
print('Categorical:', categorical_features)


Features used: ['Unnamed: 0', 'Herstellernummer', 'Werksnummer', 'Logistikverzug_Arbeitstage']
Automatically removed ID-like fields: []
Numeric: ['Unnamed: 0', 'Herstellernummer', 'Werksnummer', 'Logistikverzug_Arbeitstage']
Categorical: []


In [29]:
# ---------- Train / tune decision tree ----------
if y.nunique() < 2:
    raise ValueError('Decision-tree classification requires both defective and non-defective observations.')

X_train, X_test, y_train, y_test = train_test_split(
    X, y,
    test_size=0.25,
    random_state=42,
    stratify=y,
)

numeric_pipe = Pipeline([
    ('imputer', SimpleImputer(strategy='median')),
])

categorical_pipe = Pipeline([
    ('imputer', SimpleImputer(strategy='most_frequent')),
    ('onehot', OneHotEncoder(handle_unknown='ignore', sparse_output=False)),
])

preprocessor = ColumnTransformer([
    ('num', numeric_pipe, numeric_features),
    ('cat', categorical_pipe, categorical_features),
], remainder='drop')

pipe = Pipeline([
    ('prep', preprocessor),
    ('tree', DecisionTreeClassifier(random_state=42, class_weight='balanced')),
])

param_grid = {
    'tree__criterion': ['gini', 'entropy'],
    'tree__max_depth': [2, 3, 4, 5, 6, None],
    'tree__min_samples_leaf': [1, 2, 5, 10],
}

# Use as many folds as the minority class safely allows, capped at 5.
minority_n = y_train.value_counts().min()
n_splits = int(min(5, minority_n))
if n_splits < 2:
    raise ValueError('Too few observations in the minority class for stratified cross-validation.')

cv = StratifiedKFold(n_splits=n_splits, shuffle=True, random_state=42)

# F1 is appropriate when defective parts are relatively rare and recall/precision both matter.
grid = GridSearchCV(
    pipe,
    param_grid=param_grid,
    scoring='f1',
    cv=cv,
    n_jobs=-1,
    refit=True,
)
grid.fit(X_train, y_train)

best_tree = grid.best_estimator_
print('Best parameters:', grid.best_params_)
print(f'Best CV F1: {grid.best_score_:.3f}')


Best parameters: {'tree__criterion': 'gini', 'tree__max_depth': 3, 'tree__min_samples_leaf': 1}
Best CV F1: 0.000


In [30]:
# ---------- Test-set evaluation ----------
y_pred = best_tree.predict(X_test)

print(classification_report(y_test, y_pred, target_names=['Not defective', 'Defective'], zero_division=0))

cm = confusion_matrix(y_test, y_pred)
fig = px.imshow(
    cm,
    text_auto=True,
    x=['Predicted not defective', 'Predicted defective'],
    y=['Actual not defective', 'Actual defective'],
    title='Decision-tree confusion matrix',
    labels=dict(x='Prediction', y='Actual', color='Count'),
)
fig.update_layout(template='plotly_white')
fig.show()

if y_test.nunique() == 2 and hasattr(best_tree, 'predict_proba'):
    y_prob = best_tree.predict_proba(X_test)[:, 1]
    print(f'Test ROC-AUC: {roc_auc_score(y_test, y_prob):.3f}')


               precision    recall  f1-score   support

Not defective       1.00      0.87      0.93     76621
    Defective       0.00      0.50      0.00         2

     accuracy                           0.87     76623
    macro avg       0.50      0.68      0.46     76623
 weighted avg       1.00      0.87      0.93     76623



Test ROC-AUC: 0.815


In [31]:
# ---------- Interpretability: feature importances and tree visualization ----------
prep = best_tree.named_steps['prep']
tree_model = best_tree.named_steps['tree']

feature_names = prep.get_feature_names_out()
importances = pd.DataFrame({
    'Feature': feature_names,
    'Importance': tree_model.feature_importances_
}).sort_values('Importance', ascending=False)

importance_plot = importances[importances['Importance'] > 0].head(15).sort_values('Importance')
fig = px.bar(
    importance_plot,
    x='Importance',
    y='Feature',
    orientation='h',
    title='Decision-tree feature importances (non-zero, top 15)'
)
fig.update_layout(template='plotly_white')
fig.show()

display(importances.head(20))

# A literal tree diagram is useful for explaining the final decision rules.
plt.figure(figsize=(22, 10))
plot_tree(
    tree_model,
    feature_names=feature_names,
    class_names=['Not defective', 'Defective'],
    filled=True,
    rounded=True,
    max_depth=4,
    fontsize=8,
)
plt.title('Decision tree for K7 defect classification')
plt.show()


,Feature,Importance
0,num__Unnamed: 0,1.0
1,num__Herstellernummer,0.0
2,num__Werksnummer,0.0
3,num__Logistikverzug_Arbeitstage,0.0


InvalidParameterError: The 'feature_names' parameter of plot_tree must be an instance of 'list' or None. Got array(['num__Unnamed: 0', 'num__Herstellernummer', 'num__Werksnummer',
       'num__Logistikverzug_Arbeitstage'], dtype=object) instead.

<Figure size 2200x1000 with 0 Axes>

## Submission notes

- The generated dataset is written to `data/processed/general_tasks/Logistics delay.csv`.
- Keep the notebook in `notebooks/general_tasks/` and run it from top to bottom so outputs are embedded before exporting.
- After running the notebook, export the fully executed notebook to HTML under `exports/` as required by the project structure.
- In the written discussion for part (d), explicitly state which variables were excluded to prevent target leakage.